# Access to education by public transport in Montevideo

This report examines how many public primary and secondary education centers residents can reach within 15, 30, and 45 minutes by public transport and walking. The two education subsystems are reported separately:

- **DGEIP**: Dirección General de Educación Inicial y Primaria (legacy source name: CEIP)
- **DGES**: Dirección General de Educación Secundaria (legacy source name: CES)

In [1]:
from pathlib import Path
import datetime

import altair as alt
import attaviz
import contextily as cx
import folium
import geopandas as gpd
import pandas as pd
import r5py
from IPython.display import display


attaviz.enable()


def find_project_root(marker="pyproject.toml"):
    current = Path.cwd()
    for parent in [current, *current.parents]:
        if (parent / marker).exists():
            return parent
    raise FileNotFoundError(f"Could not find {marker}")


def simplify_for_web(frame, tolerance=30):
    display_frame = frame.to_crs(LOCAL_CRS).copy()
    display_frame.geometry = display_frame.geometry.simplify(
        tolerance, preserve_topology=True
    )
    return display_frame.to_crs(WGS84_CRS)


PROJECT_ROOT = find_project_root()
DATA_PATH = PROJECT_ROOT / "data"
EDUCATION_PATH = DATA_PATH / "education"
POPULATION_PATH = DATA_PATH / "population" / "poblacion-zonificacion.gpkg"
SKIMS_PATH = DATA_PATH / "skims"
REPORT_RESULTS_PATH = PROJECT_ROOT / "reports" / "results"
REPORT_FIGURES_PATH = PROJECT_ROOT / "reports" / "figures"

TILES = cx.providers.Esri.WorldGrayCanvas
LOCAL_CRS = "EPSG:32721"
WGS84_CRS = "EPSG:4326"
THRESHOLDS = (15, 30, 45)
SCENARIOS = (
    "wed_07",
    "wed_08",
    "wed_09",
    "wed_10",
    "sat_07",
    "sat_08",
    "sat_09",
    "sat_10",
)
SCENARIO_LABELS = {
    "wed_07": "Wednesday 07:00",
    "wed_08": "Wednesday 08:00",
    "wed_09": "Wednesday 09:00",
    "wed_10": "Wednesday 10:00",
    "sat_07": "Saturday 07:00",
    "sat_08": "Saturday 08:00",
    "sat_09": "Saturday 09:00",
    "sat_10": "Saturday 10:00",
}

REPORT_RESULTS_PATH.mkdir(parents=True, exist_ok=True)
REPORT_FIGURES_PATH.mkdir(parents=True, exist_ok=True)

## Data sources and preparation

| Dataset | Details |
|---|---|
| Population zoning | `poblacion-zonificacion.gpkg`: source population and zone polygons |
| DGEIP workbook and CEIP shapefile | DGEIP center attributes, enrollment, and point locations |
| Wednesday/Saturday skim matrices | Median public-transport and walking travel time between population-zone centroids |

The source filenames retain the former council acronyms CEIP and CES. This report uses the current subsystem names DGEIP and DGES.

In [2]:
dgeip_shape_path = EDUCATION_PATH / "dgeip" / "CEIP.shp"
dges_shape_path = EDUCATION_PATH / "dges" / "CES.shp"

population_zones = (
    gpd.read_file(POPULATION_PATH)
    .rename(columns={"id_poligono": "zone_id", "poblacion": "population"})
    .to_crs(LOCAL_CRS)
)

dgeip_gdf = (
    gpd.read_file(dgeip_shape_path)
    .to_crs(LOCAL_CRS)
    .rename(columns={"Nombre": "name", "RUEE": "center_id"})
)
dges_gdf = (
    gpd.read_file(dges_shape_path)
    .to_crs(LOCAL_CRS)
    .rename(columns={"FIRST_Nomb": "name", "Ruee_Calcu": "center_id"})
)

In [3]:
education_map = simplify_for_web(population_zones).explore(
    color="#d9d9d9",
    tiles=TILES,
    name="Population zones",
    style_kwds={"weight": 0.35, "fillOpacity": 0.08},
)

dgeip_gdf.to_crs(WGS84_CRS).explore(
    m=education_map,
    color="#2b8cbe",
    marker_type="circle_marker",
    marker_kwds={"radius": 3, "fill": True},
    tooltip=["name"],
    name="DGEIP centers",
)
dges_gdf.to_crs(WGS84_CRS).explore(
    m=education_map,
    color="#e6550d",
    marker_type="circle_marker",
    marker_kwds={"radius": 4, "fill": True},
    tooltip=["name"],
    name="DGES centers",
)
folium.LayerControl(collapsed=False).add_to(education_map)
education_map

## Accessibility method

Each education center is assigned to the population destination zone containing its point. Travel time therefore represents the median (`p50`) time from the origin-zone centroid to the destination-zone centroid--not to the exact school location.

For origin zone *i*, subsystem *s*, and threshold *t*:

$$
A_{i,s}(t) = \sum_j \left[\mathrm{centers}_{j,s} \times \mathbf{1}\!\left(\mathrm{travel\_time}_{ij} \le t\right)\right]
$$

Regional results are reported as both an unweighted mean and a population-weighted mean. The population-weighted mean is:

$$
A_{\mathrm{population},s}(t)
=
\frac{\sum_i \left[\mathrm{population}_i \times A_{i,s}(t)\right]}
{\sum_i \mathrm{population}_i}
$$

In [4]:
dgeip_zones = gpd.sjoin(
    dgeip_gdf,
    population_zones[["zone_id", "geometry"]],
    how="right",
    predicate="within",
)

dges_zones = gpd.sjoin(
    dges_gdf,
    population_zones[["zone_id", "geometry"]],
    how="right",
    predicate="within",
)

dgeip_weights = (
    dgeip_zones.groupby("zone_id", as_index=False)
    .agg(centers=("center_id", "count"))
    .assign(subsystem="DGEIP")
)

dges_weights = (
    dges_zones.groupby("zone_id", as_index=False)
    .agg(centers=("center_id", "count"))
    .assign(subsystem="DGES")
)
destination_weights = pd.concat([dgeip_weights, dges_weights], ignore_index=True)
destination_weights.head()

,zone_id,centers,subsystem
0,0,3,DGEIP
1,1,0,DGEIP
2,2,0,DGEIP
3,3,1,DGEIP
4,4,0,DGEIP


The first two maps show the number of DGEIP and DGES centers for each zone, while the last two maps show the density of these centers per 100 km².

In [5]:
zone_center_maps = {}
zone_center_density_maps = {}
for subsystem, color_map in {"DGEIP": "Blues", "DGES": "Oranges"}.items():
    zone_counts = destination_weights.loc[
        destination_weights["subsystem"].eq(subsystem), ["zone_id", "centers"]
    ]
    map_frame = population_zones.merge(zone_counts, on="zone_id", how="left")
    map_frame["centers"] = map_frame["centers"].fillna(0)
    map_frame["area_km2"] = map_frame.geometry.area / 1_000_000
    map_frame["centers_per_100_km2"] = (
        100 * map_frame["centers"] / map_frame["area_km2"]
    )
    zone_center_maps[subsystem] = simplify_for_web(map_frame).explore(
        column="centers",
        cmap=color_map,
        legend=True,
        tooltip=["zone_id", "tipo_zona", "population", "centers"],
        tiles=TILES,
        legend_kwds={"caption": f"{subsystem} centers located in each zone"},
        style_kwds={"weight": 0.35, "color": "white", "fillOpacity": 0.75},
    )
    zone_center_density_maps[subsystem] = simplify_for_web(map_frame).explore(
        column="centers_per_100_km2",
        cmap=color_map,
        legend=True,
        tooltip=[
            "zone_id",
            "tipo_zona",
            "population",
            "area_km2",
            "centers",
            "centers_per_100_km2",
        ],
        tiles=TILES,
        legend_kwds={"caption": f"{subsystem} centers per 100 km²"},
        style_kwds={"weight": 0.35, "color": "white", "fillOpacity": 0.75},
    )

display(zone_center_maps["DGEIP"])
display(zone_center_maps["DGES"])
display(zone_center_density_maps["DGEIP"])
display(zone_center_density_maps["DGES"])


In [6]:
SKIM_NETWORK_PATH = DATA_PATH / "uruguay-260624.osm.pbf"
SKIM_FEEDS = [
    DATA_PATH / "GTFS" / "google_transit.zip",
    DATA_PATH / "GTFS" / "gtfs_20260326.zip",
]
SKIM_DEPARTURES = {
    "wed_07": datetime.datetime(2026, 3, 25, 7),
    "wed_08": datetime.datetime(2026, 3, 25, 8),
    "wed_09": datetime.datetime(2026, 3, 25, 9),
    "wed_10": datetime.datetime(2026, 3, 25, 10),
    "sat_07": datetime.datetime(2026, 3, 28, 7),
    "sat_08": datetime.datetime(2026, 3, 28, 8),
    "sat_09": datetime.datetime(2026, 3, 28, 9),
    "sat_10": datetime.datetime(2026, 3, 28, 10),
}


def generate_skims(overwrite=False):
    missing = [path for path in [SKIM_NETWORK_PATH, *SKIM_FEEDS] if not path.exists()]
    if missing:
        raise FileNotFoundError("Missing skim inputs: " + ", ".join(map(str, missing)))

    points = population_zones[["zone_id", "geometry"]].copy()
    points["geometry"] = points.geometry.centroid
    points = points.rename(columns={"zone_id": "id"}).to_crs(WGS84_CRS)
    SKIMS_PATH.mkdir(parents=True, exist_ok=True)
    if not overwrite and all(
        (SKIMS_PATH / f"{scenario}.parquet").exists() for scenario in SCENARIOS
    ):
        print(f"All skim files already exist in {SKIMS_PATH}")
        return
    network = r5py.TransportNetwork(SKIM_NETWORK_PATH, SKIM_FEEDS)

    for scenario in SCENARIOS:
        output_path = SKIMS_PATH / f"{scenario}.parquet"
        if output_path.exists() and not overwrite:
            print(f"Skipping {scenario}: {output_path} already exists")
            continue

        travel_times = r5py.TravelTimeMatrix(
            network,
            origins=points,
            destinations=points,
            departure=SKIM_DEPARTURES[scenario],
            departure_time_window=datetime.timedelta(minutes=60),
            percentiles=[25, 50, 75],
            transport_modes=[r5py.TransportMode.TRANSIT, r5py.TransportMode.WALK],
            snap_to_network=True,
        )
        skim = travel_times.rename(
            columns={
                "travel_time_p25": "p25",
                "travel_time_p50": "p50",
                "travel_time_p75": "p75",
            }
        )[["from_id", "to_id", "p25", "p50", "p75"]]
        temporary_path = output_path.with_name(output_path.name + ".tmp")
        skim.to_parquet(temporary_path, index=False)
        temporary_path.replace(output_path)
        print(f"Wrote {output_path} ({len(skim)} pairs)")


RUN_SKIM_GENERATION = False
OVERWRITE_SKIMS = False
if RUN_SKIM_GENERATION:
    generate_skims(overwrite=OVERWRITE_SKIMS)


In [7]:
def calculate_scenario(weights: pd.DataFrame, scenario: str):
    subsystem = weights.loc[0, "subsystem"]
    matrix = pd.read_parquet(SKIMS_PATH / f"{scenario}.parquet")
    pairs = matrix.filter(["from_id", "to_id", "p50"]).merge(
        weights, left_on="to_id", right_on="zone_id", how="left"
    )
    score_columns = []
    for minutes in THRESHOLDS:
        center_column = f"centers_{minutes}min"
        pairs[center_column] = (
            pairs["centers"].fillna(0).where(pairs["p50"] <= minutes, 0)
        )
        score_columns.append(center_column)
    scores = pairs.groupby("from_id", as_index=False)[score_columns].sum()
    scores_pop = (
        population_zones.filter(["zone_id", "population", "geometry"])
        .merge(scores, left_on="zone_id", right_on="from_id", how="left")
        .assign(
            subsystem=subsystem,
            scenario=scenario,
            scenario_label=SCENARIO_LABELS[scenario],
        )
        .drop(columns=["from_id"])
    )

    valid = scores_pop["population"].notna()
    denominator = scores_pop.loc[valid, "population"].sum()
    centers_total = weights["centers"].sum()
    records = []
    for minutes in THRESHOLDS:
        centers_mean = scores_pop[f"centers_{minutes}min"].fillna(0).mean()
        center_weighted_mean = (
            scores_pop.loc[valid, "population"]
            * scores_pop.loc[valid, f"centers_{minutes}min"].fillna(0)
        ).sum() / denominator
        record = {
            "scenario": scenario,
            "scenario_label": SCENARIO_LABELS[scenario],
            "subsystem": subsystem,
            "threshold_minutes": minutes,
            "centers_mean": centers_mean,
            "population_weighted_centers_mean": center_weighted_mean,
            "centers_reachable_pct": 100 * centers_mean / centers_total,
            "population_weighted_centers_reachable_pct": 100
            * center_weighted_mean
            / centers_total,
        }
        records.append(record)
    return pd.DataFrame(records), scores_pop


scenario_results = []
scores_pops = []
for scenario in SCENARIOS:
    for weights in [dgeip_weights, dges_weights]:
        results, scores_pop = calculate_scenario(weights, scenario)
        scenario_results.append(results)
        scores_pops.append(scores_pop)

scenario_results = pd.concat(scenario_results, ignore_index=True)
scores_pops = pd.concat(scores_pops, ignore_index=True)
scores_pops.to_parquet(
    REPORT_RESULTS_PATH / "education_accessibility_scores_pops.parquet", index=False
)
scenario_results.to_parquet(
    REPORT_RESULTS_PATH / "education_accessibility_by_scenario.parquet", index=False
)

## Baseline results: Wednesday 08:00

At the 30-minute reference threshold, the unweighted mean is 27 DGEIP centers and 9 DGES centers. These represent 2.1% and 4.6% centers, respectively, of all centers in Montevideo.

The population-weighted mean is 39 DGEIP centers and 8 DGES centers. These represent 3.0% and 4.1% centers, respectively, of all centers in Montevideo.

In [8]:
baseline_results = scenario_results.query("scenario == 'wed_08'")

baseline_chart = (
    alt.Chart(baseline_results)
    .mark_bar()
    .encode(
        x=alt.X(
            "threshold_minutes:O",
            title="Travel-time threshold (minutes)",
            sort=list(THRESHOLDS),
        ),
        y=alt.Y("centers_reachable_pct:Q", title="Centers reachable (%)"),
        color=alt.Color(
            "subsystem:N",
            title="Subsystem",
            scale=alt.Scale(domain=["DGEIP", "DGES"], range=["#2b8cbe", "#e6550d"]),
        ),
        xOffset="subsystem:N",
        tooltip=[
            "subsystem:N",
            alt.Tooltip("threshold_minutes:O", title="Minutes"),
            alt.Tooltip(
                "centers_mean:Q",
                title="mean centers",
                format=".2f",
            ),
            alt.Tooltip(
                "centers_reachable_pct:Q",
                title="Centers reachable",
                format=".2f",
            ),
        ],
    )
    .properties(
        title=alt.Title(
            text="Average education access, Wednesday 08:00",
            subtitle="At the 30-minute reference threshold",
        ),
        width=560,
        height=330,
    )
)

baseline_chart

alt.Chart(...)

In [9]:
baseline_results = scenario_results.query("scenario == 'wed_08'")

baseline_chart = (
    alt.Chart(baseline_results)
    .mark_bar()
    .encode(
        x=alt.X(
            "threshold_minutes:O",
            title="Travel-time threshold (minutes)",
            sort=list(THRESHOLDS),
        ),
        y=alt.Y(
            "population_weighted_centers_reachable_pct:Q",
            title="Population-weighted centers reachable (%)",
        ),
        color=alt.Color(
            "subsystem:N",
            title="Subsystem",
            scale=alt.Scale(domain=["DGEIP", "DGES"], range=["#2b8cbe", "#e6550d"]),
        ),
        xOffset="subsystem:N",
        tooltip=[
            "subsystem:N",
            alt.Tooltip("threshold_minutes:O", title="Minutes"),
            alt.Tooltip(
                "population_weighted_centers_mean:Q",
                title="Population-weighted mean centers",
                format=".2f",
            ),
            alt.Tooltip(
                "population_weighted_centers_reachable_pct:Q",
                title="Population-weighted centers reachable",
                format=".2f",
            ),
        ],
    )
    .properties(
        title=alt.Title(
            text="Population-weighted education access, Wednesday 08:00",
            subtitle="At the 30-minute reference threshold",
        ),
        width=560,
        height=330,
    )
)

baseline_chart


alt.Chart(...)

The choropleth map below shows the number of DGEIP and DGES centers reachable within the 30-minute reference threshold across Montevideo.

Several zones, including 552, 553, 554, 543, and 544, appear more accessible than the city core, despite the core having a denser transport network. This pattern occurs because schools are assigned to destination zones, and travel within the same zone is recorded as zero minutes. Thus, every school located in the same zone, regardless of its actual distance from the zone centroid, is considered reachable within the reference threshold.

This issue affects beyond just the few zones mentioned above, as it impacts 29 zones that have only a zero-minute self-pair available.

In [10]:
skim = pd.read_parquet(SKIMS_PATH / "wed_08.parquet")

finite_destinations = skim.groupby("from_id", as_index=False)["p50"].agg(
    reachable_count=lambda x: x.notna().sum()
)
self_only_zone_ids = finite_destinations.query("reachable_count == 1").reset_index(
    drop=True
)
self_only_zone_ids

,from_id,reachable_count
0,0,1
1,323,1
2,324,1
3,325,1
4,327,1
5,430,1
6,432,1
7,437,1
8,451,1
9,463,1


In [11]:
baseline_scores_pop = scores_pops.query("scenario == 'wed_08'")

accessibility_maps = {}
for subsystem, color_map in {"DGEIP": "Blues", "DGES": "Oranges"}.items():
    provider_zones = baseline_scores_pop[
        baseline_scores_pop["subsystem"].eq(subsystem)
    ][["zone_id", "centers_30min"]]
    map_frame = population_zones.merge(provider_zones, on="zone_id", how="left")
    map_frame["centers_30min"] = map_frame["centers_30min"].fillna(0)
    provider_map = simplify_for_web(map_frame).explore(
        column="centers_30min",
        cmap=color_map,
        scheme="Quantiles",
        k=5,
        legend=True,
        tooltip=["zone_id", "tipo_zona", "population", "centers_30min"],
        tiles=TILES,
        legend_kwds={"caption": f"{subsystem} centers reachable in 45 minutes"},
        style_kwds={"weight": 0.35, "color": "white", "fillOpacity": 0.75},
    )
    provider_map.save(
        REPORT_FIGURES_PATH / f"{subsystem.lower()}_accessibility_wed_08_45min.html"
    )
    accessibility_maps[subsystem] = provider_map

display(accessibility_maps["DGEIP"])
display(accessibility_maps["DGES"])